# Comparing the versions

## Combine the JSON data

In [1]:
import os
import json

# List of JSON files to combine.
json_files = ['N1904/N1904-John.json', 'KJTR/KJTR-John.json', 'TCGNT/TCGNT-John.json', 'TISCH/TISCH-John.json', 'SBL/SBL-John.json', 'SR/SR-John.json' ]

# Dictionary to hold the combined data.
# The structure will be: { tag: { source: text, ... }, ... }
combined = {}

# Process each JSON file.
for file in json_files:
    # Derive a source key from the filename.
    source = os.path.basename(file).split('-')[0]
    with open(file, 'r', encoding='utf-8') as f:
        data = json.load(f)
        # Each file contains a list of entries.
        for entry in data:
            tag = entry["tag"]
            text = entry["text"]
            # If this tag hasn't been seen before, initialize its dictionary.
            if tag not in combined:
                combined[tag] = {}
            # Store the text for the current source.
            combined[tag][source] = text


# Write the combined JSON to an output file with indentation for readability.
with open('Combined-John.json', 'w', encoding='utf-8') as f:
    json.dump(combined, f, ensure_ascii=False, indent=4)


In [2]:
# dump the first two items from the dictionairy
first_two = dict(list(combined.items())[:2])
print(json.dumps(first_two, ensure_ascii=False, indent=4))

{
    "43001001": {
        "N1904": "εν αρχη ην ο λογος, και ο λογος ην προς τον θεον, και θεος ην ο λογος. ",
        "KJTR": " εν αρχη ην ο λογος, και ο λογος ην προς τον θεον, και θεος ην ο λογος.",
        "TCGNT": "εν αρχη ην ο λογος, και ο λογος ην προς τον θεον, και θεος ην ο λογος. ",
        "TISCH": "εν αρχη ην ο λογος, και ο λογος ην προς τον θεον, και θεος ην ο λογος. ",
        "SBL": "εν αρχη ην ο λογος, και ο λογος ην προς τον θεον, και θεος ην ο λογος. ",
        "SR": " εν αρχη ην ο λογος, και ο λογος ην προς τον θεον, και θεος ην ο λογος."
    },
    "43001002": {
        "N1904": "ουτος ην εν αρχη προς τον θεον. ",
        "KJTR": " ουτος ην εν αρχη προς τον θεον.",
        "TCGNT": "ουτος ην εν αρχη προς τον θεον. ",
        "TISCH": "ουτος ην εν αρχη προς τον θεον. ",
        "SBL": "ουτος ην εν αρχη προς τον θεον. ",
        "SR": " ουτος ην εν αρχη προς τον θεον."
    }
}


In [15]:
import re
import json
import difflib
import unicodedata

def normalize(string):
    """
    Normalize the input string by converting it to lowercase and removing diacritical marks.
    This is achieved using Unicode normalization (NFD) and filtering out non-spacing marks.
    """
    string = string.lower()
    string = unicodedata.normalize('NFD', string)
    return ''.join(ch for ch in string if unicodedata.category(ch) != 'Mn')

def tokenize(text):
    """
    Tokenize the text into a list of (word, punctuation) tuples.
    The regex captures a non-space word and any punctuation immediately following it.
    """
    # Append a space to capture the last token.
    pattern = re.compile(r"(\S+?)([.·,;:?!…]*)\s", re.UNICODE)
    tokens = pattern.findall(text + " ")
    return tokens

def find_fuzzy_match(base_word, tokens, start_index, base_tokens, base_index, threshold=0.40, n=3, backtrack=8):
    """
    Attempt to find a fuzzy match for base_word in the list of candidate tokens, 
    starting at start_index.
    
    First, it iterates token-by-token comparing normalized forms. If no acceptable match 
    is found, it will then attempt a catch-up procedure using an n-gram strategy:
      - It goes back up to 'backtrack' tokens from the current base_index to build an
        n-gram from base_tokens.
      - It then searches the candidate tokens for an n-gram match (using the same 
        normalization and similarity threshold).
      - If an n-gram match is found, it uses the relative offset within the n-gram to 
        return a match for base_word.
    
    Parameters:
      base_word: the target word from the base text.
      tokens: list of (word, punctuation) tuples from the candidate text.
      start_index: the index in tokens to start searching from.
      base_tokens: the full token list for the base text.
      base_index: the index of base_word within base_tokens.
      threshold: similarity threshold for a match.
      n: size of the n-gram to use during catch-up.
      backtrack: number of tokens to step back in the base text when forming the n-gram.
    
    Returns a tuple (index, punctuation) if a match is found; otherwise it returns (None, '').
    """
    norm_base = normalize(base_word)
    # First try direct fuzzy matching.
    for i in range(start_index, len(tokens)):
        candidate_word, punctuation = tokens[i]
        norm_candidate = normalize(candidate_word)
        # Check if one is contained in the other.
        if norm_base in norm_candidate or norm_candidate in norm_base:
            return i, punctuation
        # Otherwise, check the similarity ratio.
        similarity = difflib.SequenceMatcher(None, norm_base, norm_candidate).ratio()
        if similarity >= threshold:
            return i, punctuation

    # If no match is found, trigger catch-up using an n-gram.
    back_index = max(0, base_index - backtrack)
    # Build the n-gram from the base tokens (using only the word parts).
    ngram_tokens = [base_tokens[j][0] for j in range(back_index, min(back_index + n, len(base_tokens)))]
    ngram = " ".join(normalize(word) for word in ngram_tokens)
    
    # Now search in candidate tokens for a matching n-gram.
    for i in range(start_index, len(tokens) - n + 1):
        candidate_ngram_tokens = [tokens[j][0] for j in range(i, i + n)]
        candidate_ngram = " ".join(normalize(word) for word in candidate_ngram_tokens)
        similarity_ngram = difflib.SequenceMatcher(None, ngram, candidate_ngram).ratio()
        if similarity_ngram >= threshold:
            # Calculate the offset of base_word relative to the beginning of the n-gram.
            offset = base_index - back_index
            target_index = i + offset
            if target_index < len(tokens):
                return target_index, tokens[target_index][1]
    return None, ''

# Load the combined JSON input file.
with open("Combined-John.json", "r", encoding="utf-8") as f:
    combined = json.load(f)

# The JSON structure is assumed to be a dictionary:
# {
#    "4300101": {"N1904": "text...", "KJTR": "text...", "SBL": "text...", ... },
#    "4300102": {...},
#    ...
# }
# Define the version names (keys) that appear in the JSON.
var_names = ["N1904", "KJTR", "SBL", "SR", "TCGNT", "TISCH"]

# Initialize a dictionary to accumulate full texts for each version.
texts_by_source = {var: [] for var in var_names}

# Sort the tags to ensure the texts are in order.
for tag in sorted(combined.keys()):
    entry = combined[tag]
    for var in var_names:
        # Append the text fragment; if missing, use an empty string.
        texts_by_source[var].append(entry.get(var, ""))

# Join the fragments to create full texts.
docN1904 = "".join(texts_by_source["N1904"])
docKJTR = "".join(texts_by_source["KJTR"])
docSBL   = "".join(texts_by_source["SBL"])
docSR    = "".join(texts_by_source["SR"])
codTCGNT = "".join(texts_by_source["TCGNT"])
docTISCH = "".join(texts_by_source["TISCH"])

# Build a list of texts in the desired order.
texts = [docN1904, docKJTR, docSBL, docSR, codTCGNT, docTISCH]


# Tokenize each text.
token_lists = [tokenize(text) for text in texts]

# Use the tokens from the base text (docN1904) as the reference.
base_tokens = token_lists[0]

# Initialize pointers for each version.
pointers = [0 for _ in token_lists]

output_data = []
# Iterate over the base tokens with index so that we can pass base_index.
for base_index, (base_word, base_punct) in enumerate(base_tokens):
    entry = {"word_index": base_index + 1, "word": base_word, var_names[0]: base_punct}
    for ver in range(1, len(token_lists)):
        idx, punct = find_fuzzy_match(
            base_word,
            token_lists[ver],
            pointers[ver],
            base_tokens,
            base_index,
            threshold=1,    # sets how similar two words (or n-grams) must be to be considered a match.
            n=1,            # determines the size of the n-gram used in the catch-up phase.
            backtrack=10    # specifies how far back in the base text to start the n-gram
        )
        if idx is not None:
            pointers[ver] = idx + 1  # Update the pointer for that version.
        else:
            punct = ""  # No match found.
        entry[var_names[ver]] = punct
    output_data.append(entry)

# Optionally, filter for cases where the base text has no punctuation but any other version does.
differences = [
    entry for entry in output_data
    if entry[var_names[0]] == "" and any(entry[var] for var in var_names[1:])
]

# Write the punctuation comparison JSON to an output file.
with open("punctuation_comparison.json", "w", encoding="utf-8") as out_file:
    json.dump(output_data, out_file, ensure_ascii=False, indent=2)


# Compare

In [16]:
len(differences) # meaning additional punctuations

29

# combined text 

In [17]:
import json

# Open and load the JSON file produced by the previous script.
with open("punctuation_comparison.json", "r", encoding="utf-8") as f:
    data = json.load(f)

# Define the keys corresponding to your texts.
version_keys = ["N1904", "KJTR", "SBL", "SR", "TISCH"]

composite_words = []

for entry in data:
    word = entry["word"]
    # Gather punctuation from all versions.
    puncs = [entry[key] for key in version_keys]
    # Create a set of unique punctuation options.
    unique_puncs = set(puncs)
    
    # If all versions agree (i.e. the set has exactly one value)
    if len(unique_puncs) == 1:
        agreed_punc = unique_puncs.pop()
        composite_word = word + agreed_punc
    else:
        # There is disagreement: sort the unique options and join them with a slash.
        options = sorted(unique_puncs)
        composite_word = word + "[" + "/".join(options) + "]"
    
    composite_words.append(composite_word)

# Optionally, join the composite words into a full text (separated by a space).
composite_text = " ".join(composite_words)

# Write the result to a file.
with open("composite_text.txt", "w", encoding="utf-8") as out_file:
    out_file.write(composite_text)
    
composite_text[:500]

'εν αρχη ην ο λογος, και ο λογος ην προς τον θεον, και θεος ην ο λογος. ουτος ην εν αρχη προς τον θεον. παντα δι᾽ αυτου εγενετο[,/·] και χωρις αυτου εγενετο ουδε εν[/.] ο γεγονεν[/.] εν αυτω ζωη ην[/,/·] και η ζωη ην το φως[/,] των ανθρωπων[/./·] και το φως εν τη σκοτια φαινει[/,/·] και η[/,] σκοτια αυτο ου[/·] κατελαβεν[/.] εγενετο ανθρωπος[/,] απεσταλμενος παρα θεου[/,] ονομα αυτω[/,] ιωανης[/·] ουτος ηλθεν εις μαρτυριαν[/,] ινα μαρτυρηση περι[/,/.] του φωτος[/,] ινα παντες πιστευσωσιν δι᾽ αυτο'

# individual text version

## N1904 with its standard punctuation

In [18]:
import json

# Open and load the JSON file produced by the previous script.
with open("punctuation_comparison.json", "r", encoding="utf-8") as f:
    data = json.load(f)

# Initialize a list to contain the results 
composite_N1904=[]

for entry in data:
    word = entry["word"]
    punct = entry["N1904"]
    composite_word = word + punct
    composite_N1904.append(composite_word)

# Write the result to a file.
with open("N1904base_N1904punct.txt", "w", encoding="utf-8") as out_file:
    out_file.write(" ".join(composite_N1904))
    
# Print the first 250 words     
print(" ".join(composite_N1904[:250]))

εν αρχη ην ο λογος, και ο λογος ην προς τον θεον, και θεος ην ο λογος. ουτος ην εν αρχη προς τον θεον. παντα δι᾽ αυτου εγενετο, και χωρις αυτου εγενετο ουδε εν ο γεγονεν. εν αυτω ζωη ην, και η ζωη ην το φως των ανθρωπων. και το φως εν τη σκοτια φαινει, και η σκοτια αυτο ου κατελαβεν. εγενετο ανθρωπος, απεσταλμενος παρα θεου, ονομα αυτω ιωανης· ουτος ηλθεν εις μαρτυριαν, ινα μαρτυρηση περι του φωτος, ινα παντες πιστευσωσιν δι᾽ αυτου. ουκ ην εκεινος το φως, αλλ᾽ ινα μαρτυρηση περι του φωτος. ην το φως το αληθινον, ο φωτιζει παντα ανθρωπον, ερχομενον εις τον κοσμον. εν τω κοσμω ην, και ο κοσμος δι᾽ αυτου εγενετο, και ο κοσμος αυτον ουκ εγνω. εις τα ιδια ηλθεν, και οι ιδιοι αυτον ου παρελαβον. οσοι δε ελαβον αυτον, εδωκεν αυτοις εξουσιαν τεκνα θεου γενεσθαι, τοις πιστευουσιν εις το ονομα αυτου, οι ουκ εξ αιματων ουδε εκ θεληματος σαρκος ουδε εκ θεληματος ανδρος αλλ᾽ εκ θεου εγεννηθησαν. και ο λογος σαρξ εγενετο και εσκηνωσεν εν ημιν, και εθεασαμεθα την δοξαν αυτου, δοξαν ως μονογενους παρα

## N1904 base text with TISCH punctuation

In [19]:
import json

# Open and load the JSON file produced by the previous script.
with open("punctuation_comparison.json", "r", encoding="utf-8") as f:
    data = json.load(f)

# Initialize a list to contain the results 
composite_TISCH=[]

for entry in data:
    word = entry["word"]
    punct = entry["TISCH"]
    composite_word = word + punct
    composite_TISCH.append(composite_word)

# Write the result to a file.
with open("N1904base_TISCHpunct.txt", "w", encoding="utf-8") as out_file:
    out_file.write(" ".join(composite_TISCH))

# Print the first 250 words     
print(" ".join(composite_TISCH[:250]))

εν αρχη ην ο λογος, και ο λογος ην προς τον θεον, και θεος ην ο λογος. ουτος ην εν αρχη προς τον θεον. παντα δι᾽ αυτου εγενετο, και χωρις αυτου εγενετο ουδε εν ο γεγονεν εν αυτω ζωη ην και η ζωη ην το φως, των ανθρωπων και το φως εν τη σκοτια φαινει και η, σκοτια αυτο ου· κατελαβεν εγενετο ανθρωπος απεσταλμενος παρα θεου ονομα αυτω, ιωανης ουτος ηλθεν εις μαρτυριαν ινα μαρτυρηση περι. του φωτος ινα παντες πιστευσωσιν δι᾽ αυτου ουκ ην εκεινος το φως αλλ᾽ ινα; μαρτυρηση περι του φωτος ην το φως το αληθινον ο. φωτιζει παντα ανθρωπον ερχομενον εις τον κοσμον. εν. τω κοσμω ην και ο κοσμος δι᾽ αυτου εγενετο και ο κοσμος αυτον ουκ εγνω εις τα· ιδια ηλθεν και οι ιδιοι αυτον ου παρελαβον οσοι δε ελαβον αυτον εδωκεν αυτοις εξουσιαν τεκνα θεου γενεσθαι τοις πιστευουσιν εις το ονομα αυτου οι ουκ εξ, αιματων ουδε εκ θεληματος σαρκος ουδε εκ θεληματος ανδρος αλλ᾽ εκ θεου εγεννηθησαν και ο λογος σαρξ εγενετο και εσκηνωσεν εν ημιν και εθεασαμεθα την δοξαν αυτου δοξαν ως μονογενους παρα πατρος πληρης χ

## N1904 base text with SR punctuation

In [20]:
import json

# Open and load the JSON file produced by the previous script.
with open("punctuation_comparison.json", "r", encoding="utf-8") as f:
    data = json.load(f)

# Initialize a list to contain the results 
composite_SR=[]

for entry in data:
    word = entry["word"]
    punct = entry["SR"]
    composite_word = word + punct
    composite_SR.append(composite_word)

# Write the result to a file.
with open("N1904base_SRpunct.txt", "w", encoding="utf-8") as out_file:
    out_file.write(" ".join(composite_SR))
        
# Print the first 250 words     
print(" ".join(composite_SR[:250]))

εν αρχη ην ο λογος, και ο λογος ην προς τον θεον, και θεος ην ο λογος. ουτος ην εν αρχη προς τον θεον. παντα δι᾽ αυτου εγενετο, και χωρις αυτου εγενετο ουδε εν ο γεγονεν. εν αυτω ζωη ην, και η ζωη ην το φως των ανθρωπων. και το φως εν τη σκοτια φαινει, και η σκοτια αυτο ου κατελαβεν. εγενετο ανθρωπος απεσταλμενος παρα θεου, ονομα αυτω ιωανης ουτος ηλθεν εις μαρτυριαν ινα μαρτυρηση περι, του φωτος ινα παντες πιστευσωσιν δι᾽ αυτου ουκ ην εκεινος το φως αλλ᾽ ινα μαρτυρηση περι του φωτος ην το φως το αληθινον ο φωτιζει παντα ανθρωπον ερχομενον εις τον κοσμον εν. τω κοσμω ην και ο κοσμος δι᾽ αυτου εγενετο και ο κοσμος αυτον ουκ εγνω εις τα, ιδια ηλθεν και οι ιδιοι αυτον ου παρελαβον οσοι δε ελαβον αυτον εδωκεν αυτοις εξουσιαν τεκνα θεου γενεσθαι τοις πιστευουσιν εις το ονομα αυτου, οι ουκ εξ. αιματων ουδε εκ θεληματος σαρκος ουδε εκ θεληματος ανδρος αλλ᾽ εκ θεου εγεννηθησαν και ο λογος σαρξ εγενετο και εσκηνωσεν εν ημιν και εθεασαμεθα την δοξαν αυτου δοξαν ως μονογενους παρα πατρος πληρης χ

## N1904 base text with SBL punctuation

In [21]:
import json

# Open and load the JSON file produced by the previous script.
with open("punctuation_comparison.json", "r", encoding="utf-8") as f:
    data = json.load(f)

# Initialize a list to contain the results 
composite_SBL=[]

for entry in data:
    word = entry["word"]
    punct = entry["SBL"]
    composite_word = word + punct
    composite_SBL.append(composite_word)

# Write the result to a file.
with open("N1904base_SBLpunct.txt", "w", encoding="utf-8") as out_file:
    out_file.write(" ".join(composite_SBL))
        
# Print the first 250 words     
print(" ".join(composite_SBL[:250]))

εν αρχη ην ο λογος, και ο λογος ην προς τον θεον, και θεος ην ο λογος. ουτος ην εν αρχη προς τον θεον. παντα δι᾽ αυτου εγενετο, και χωρις αυτου εγενετο ουδε εν. ο γεγονεν εν αυτω ζωη ην, και η ζωη ην το φως των ανθρωπων· και το φως εν τη σκοτια φαινει, και η σκοτια αυτο ου κατελαβεν. εγενετο ανθρωπος απεσταλμενος παρα θεου, ονομα αυτω ιωανης ουτος ηλθεν εις μαρτυριαν ινα μαρτυρηση περι του φωτος ινα παντες πιστευσωσιν δι᾽ αυτου ουκ ην εκεινος το φως αλλ᾽ ινα μαρτυρηση περι του φωτος ην το φως το, αληθινον ο φωτιζει παντα ανθρωπον ερχομενον εις τον κοσμον. εν. τω κοσμω ην και ο κοσμος δι᾽ αυτου εγενετο και ο κοσμος αυτον ουκ εγνω εις τα· ιδια ηλθεν και οι ιδιοι αυτον ου παρελαβον οσοι δε ελαβον αυτον εδωκεν αυτοις εξουσιαν τεκνα θεου γενεσθαι τοις πιστευουσιν εις το ονομα αυτου οι ουκ εξ· αιματων ουδε εκ θεληματος σαρκος ουδε εκ θεληματος ανδρος αλλ᾽ εκ θεου εγεννηθησαν και ο λογος σαρξ εγενετο και εσκηνωσεν εν ημιν και εθεασαμεθα την δοξαν αυτου δοξαν ως μονογενους παρα πατρος πληρης χ

## N1904 base text with KJTR punctuation

In [22]:
import json

# Open and load the JSON file produced by the previous script.
with open("punctuation_comparison.json", "r", encoding="utf-8") as f:
    data = json.load(f)

# Initialize a list to contain the results 
composite_KJTR=[]

for entry in data:
    word = entry["word"]
    punct = entry["KJTR"]
    composite_word = word + punct
    composite_KJTR.append(composite_word)

# Write the result to a file.
with open("N1904base_KJTRpunct.txt", "w", encoding="utf-8") as out_file:
    out_file.write(" ".join(composite_KJTR))
    
# Print the first 250 words     
print(" ".join(composite_KJTR[:250]))

εν αρχη ην ο λογος, και ο λογος ην προς τον θεον, και θεος ην ο λογος. ουτος ην εν αρχη προς τον θεον. παντα δι᾽ αυτου εγενετο· και χωρις αυτου εγενετο ουδε εν ο γεγονεν. εν αυτω ζωη ην· και η ζωη ην το φως των ανθρωπων. και το φως εν τη σκοτια φαινει· και η σκοτια αυτο ου κατελαβεν. εγενετο ανθρωπος απεσταλμενος παρα θεου, ονομα αυτω ιωανης ουτος ηλθεν εις μαρτυριαν ινα μαρτυρηση περι, του φωτος ινα παντες πιστευσωσιν δι᾽ αυτου ουκ ην εκεινος το φως αλλ᾽ ινα; μαρτυρηση περι του φωτος ην το φως το αληθινον ο. φωτιζει παντα. ανθρωπον ερχομενον εις τον· κοσμον εν τω κοσμω ην και ο κοσμος δι᾽ αυτου εγενετο και ο κοσμος αυτον ουκ εγνω εις τα, ιδια ηλθεν και οι ιδιοι αυτον, ου παρελαβον οσοι δε ελαβον αυτον εδωκεν. αυτοις εξουσιαν τεκνα θεου γενεσθαι τοις πιστευουσιν εις το ονομα αυτου οι ουκ εξ. αιματων ουδε εκ θεληματος σαρκος ουδε εκ θεληματος ανδρος αλλ᾽ εκ θεου εγεννηθησαν, και ο λογος σαρξ εγενετο και εσκηνωσεν εν ημιν και εθεασαμεθα, την δοξαν αυτου δοξαν ως μονογενους παρα πατρος πλ

# version browser

In [23]:
# updated version

from IPython.display import HTML, display
from bokeh.io import output_notebook, show
from bokeh.models import Div
from bokeh.layouts import row, column
from bokeh.embed import file_html
from bokeh.resources import CDN 
import base64
import json
import re
import unicodedata

output_notebook()

def compute_div_height_from_lines(num_lines, line_height=25, label_height=30, padding=10):
    # Compute div height based on the number of lines.
    return label_height + (num_lines * line_height) + padding

def split_token(token):
    # Splits a token into its word part and trailing punctuation.
    i = len(token)
    while i > 0 and token[i-1] in ".,;:·":
        i -= 1
    return token[:i], token[i:]


def process_variant_token(base_token, variant_token):
    # Compare variant_token with base_token and return a tuple:
    # (effective_text, html_text)
    # where html_text contains highlighting for punctuation differences.
    base_word, base_punc = split_token(base_token)
    variant_word, variant_punc = split_token(variant_token)
    
    # Process punctuation differences first.
    if base_punc == variant_punc:
        effective = variant_word + variant_punc
        html = effective
    elif base_punc and not variant_punc:
        effective = variant_word + " "
        html = variant_word + "<span style='background-color: lightcoral;'> </span>&nbsp;"
    elif base_punc and variant_punc and variant_punc != base_punc:
        effective = variant_word + variant_punc
        html = variant_word + "<span style='background-color: lightyellow;'>" + variant_punc + "</span>"
    elif not base_punc and variant_punc:
        effective = variant_word + variant_punc
        html = variant_word + "<span style='background-color: palegreen;'>" + variant_punc + "</span>"
    else:
        effective = variant_word
        html = variant_word
    return effective, html

def process_base_token(token):
    # For the base version, return the token as both effective text and HTML.
    return token, token

def createDownloadLink(bokeh_layout, fileName, documentTitle, buttonText):
    # Convert a Bokeh layout into an HTML string, encode it as a data URI, 
    # and return an IPython HTML widget with a download link.

    # Convert the Bokeh layout to an HTML document string
    htmlContent = file_html(bokeh_layout, CDN, documentTitle)
    
    # Encode the HTML content to base64
    b64Html = base64.b64encode(htmlContent.encode('utf-8')).decode('utf-8')
    
    # Create the HTML download link
    downloadLink = f'''
    <a download="{fileName}" href="data:text/html;base64,{b64Html}">
        <button>{buttonText}</button>
    </a>
    '''
    return HTML(downloadLink)

# --- Load punctuation comparison output and build composite tokens ---
with open("punctuation_comparison.json", "r", encoding="utf-8") as f:
    comp_data = json.load(f)

# Build composite token lists (raw tokens) for each version.
# Each entry in comp_data is assumed to contain keys: "word", "N1904", "KJTR", "SBL", "SR", "TISCH".
composite_N1904 = []
composite_KJTR = []
composite_SBL = []
composite_SR = []
composite_TISCH = []

for token_data in comp_data:
    base_word = token_data["word"]
    composite_N1904.append(base_word + token_data["N1904"])
    composite_KJTR.append(base_word + token_data["KJTR"])
    composite_SBL.append(base_word + token_data["SBL"])
    composite_SR.append(base_word + token_data["SR"])
    composite_TISCH.append(base_word + token_data["TISCH"])

# Define the versions and corresponding names.
versions = [composite_N1904, composite_KJTR, composite_SBL, composite_SR, composite_TISCH]
versionnames = ["N1904", "KJTR", "SBL", "SR", "TISCH"]
num_versions = len(versions)
num_tokens = len(versions[0])  # assume all versions have the same number of tokens

# Precompute "effective" tokens for display (with highlighting).
# effective_tokens[j] is a list of tuples (effective_text, html_text) for version j.
effective_tokens = []
for j, version in enumerate(versions):
    tokens = []
    for i in range(num_tokens):
        if j == 0:
            tokens.append(process_base_token(version[i]))
        else:
            tokens.append(process_variant_token(versions[0][i], version[i]))
    effective_tokens.append(tokens)

# Adjustable variable: maximum number of characters per line.
max_chars = 75  # adjust as needed
column_width = 300

# Load verse information (assumes a JSON file with verse boundaries) 
with open('N1904/node2verse.json', 'r', encoding="utf-8") as file:
    verses = json.load(file)

verse_rows = []

# Load variant base text annotation (assumes a JSON file with only delta's)
with open('John-diff-annotated.json', 'r', encoding="utf-8") as file:
    John_diff_annotated = json.load(file)

# Process each verse.
for verse in verses:
    start_idx = verse["start"] - 1  # Convert from 1-indexed to 0-indexed.
    end_idx = verse["end"]          # end index is non-inclusive.
    num_tokens_verse = end_idx - start_idx
    verse_tag=verse["tag"]

    # Determine synchronized line breaks for the tokens of this verse.
    verse_line_indices = []  # Each element is a list of relative token indices within the verse.
    current_line = []
    current_lengths = [0] * len(effective_tokens)

    for i in range(num_tokens_verse):
        token_lengths = [len(effective_tokens[j][start_idx + i][0])
                         for j in range(len(effective_tokens))]
        if not current_line:
            new_lengths = token_lengths
        else:
            new_lengths = [current_lengths[j] + 1 + token_lengths[j]
                           for j in range(len(effective_tokens))]
        if max(new_lengths) <= max_chars:
            current_line.append(i)
            current_lengths = new_lengths
        else:
            verse_line_indices.append(current_line)
            current_line = [i]
            current_lengths = token_lengths
    if current_line:
        verse_line_indices.append(current_line)

    # Build Div columns for this verse.
    verse_divs = []

    # --- Base Version (always shown) ---
    base_lines_html = []
    for line in verse_line_indices:
        base_line_tokens = [effective_tokens[0][start_idx + i][1] for i in line]
        base_lines_html.append(" ".join(base_line_tokens))
    base_verse_content = "<br>".join(base_lines_html)
    base_label = f"<h4 style='text-align: center;'>{verse['location']} - {versionnames[0]} (base)</h4>"
    base_html = base_label + f"<p style='font-family: monospace;'>{base_verse_content}</p>"
    base_div_height = compute_div_height_from_lines(len(verse_line_indices), line_height=30, label_height=30, padding=5)
    base_div = Div(text=base_html, width=column_width, height=base_div_height)
    verse_divs.append(base_div)

    # --- Variant Versions (the variant's punctuation injected into the N1904 base text) ---
    for j in range(1, len(effective_tokens)):
        variant_lines_html = []
        for line in verse_line_indices:
            var_line_tokens = [effective_tokens[j][start_idx + i][1] for i in line]
            variant_lines_html.append(" ".join(var_line_tokens))
        variant_verse_content = "<br>".join(variant_lines_html)
        variant_label = f"<h4 style='text-align: center;'>{verse['location']} - {versionnames[j]}</h4>"

        # Check if any token's normalized word (ignoring punctuation) differs from the base N1904.
        diff_exists = False
        if verse_tag in John_diff_annotated:
            if versionnames[j] in John_diff_annotated[verse_tag]:
                #print (John_diff_annotated[verse_tag][versionnames[j]])
                diff_exists=True       
        if diff_exists:
            raw_verse_content = John_diff_annotated[verse_tag][versionnames[j]]
            variant_html = variant_label + \
                           f"<p style='font-family: monospace;'>{variant_verse_content}</p>" + \
                           f"<p style='font-family: monospace; color: grey;'>{raw_verse_content}</p>"
            variant_div_height = compute_div_height_from_lines(len(verse_line_indices)*2, line_height=30, label_height=30, padding=5)
        else:
            variant_html = variant_label + f"<p style='font-family: monospace;'>{variant_verse_content}</p>"
            variant_div_height = compute_div_height_from_lines(len(verse_line_indices), line_height=30, label_height=30, padding=5)
        variant_div = Div(text=variant_html, width=column_width, height=variant_div_height)
        verse_divs.append(variant_div)
    
    # Create a row layout for the verse (all columns).
    verse_rows.append(row(*verse_divs))
    
# Stack all verse rows vertically and display the final layout.
final_layout = column(*verse_rows)
show(final_layout)

# Create a download link for the HTML generated by Bokeh
download_link = createDownloadLink(final_layout, 
                                   'John_versions.html', 
                                   'John versions', 
                                   'Download John versions')
display(download_link)


Loading BokehJS ...